# **HO03 — Ranking Textual**

**Nome:** Gustavo Costa

Comparar modelo vetorial e BM25 no TREC-COVID round 1, usando MAP e nDCG no ranking completo e nos cortes @1, @3, @5 e @10.


In [133]:
# Importação das bibliotecas.
import json
import re
from collections import Counter
from difflib import SequenceMatcher
import xml.etree.ElementTree as arvore_xml
from pathlib import Path

import pandas as pd
from nltk.stem import PorterStemmer
from sklearn.feature_extraction.text import ENGLISH_STOP_WORDS


## **1. Carga dos dados**

Coleção [CORD-19 de 10/04/2020](https://github.com/allenai/cord19), com os textos completos disponíveis, e [consultas e julgamentos do round 1](https://ir.nist.gov/covidSubmit/data.html). Os arquivos são lidos localmente.


### **1.1. Localização dos arquivos**


In [134]:
# Permite executar a partir da raiz do projeto ou da pasta notebooks/.
pasta_projeto = Path.cwd().resolve()
if not (pasta_projeto / "data").is_dir():
    pasta_projeto = pasta_projeto.parent

pasta_dados = pasta_projeto / "data" / "round1"
pasta_colecao = pasta_dados / "2020-04-10"

arquivos_necessarios = [
    pasta_colecao / "metadata.csv",
    pasta_dados / "topics-rnd1.xml",
    pasta_dados / "qrels-rnd1.txt",
]
for caminho_arquivo in arquivos_necessarios:
    if not caminho_arquivo.is_file():
        raise FileNotFoundError(f"Arquivo não encontrado: {caminho_arquivo}")


### **1.2. Documentos e textos completos**

Cada `cord_uid` representa um documento. Antes de associar os textos, agrupamos as linhas repetidas por esse identificador e reunimos seus valores de SHA e PMC. Para título e resumo, usamos o primeiro valor preenchido na ordem do CSV. Assim, cada documento aparece uma vez sem perder caminhos disponíveis para PDF ou PMC.


In [ ]:
# Lê os campos necessários do CSV, preservando IDs e valores vazios como texto.
metadados_brutos = pd.read_csv(
    pasta_colecao / "metadata.csv",
    usecols=["cord_uid", "title", "abstract", "sha", "pmcid"],
    dtype=str,
    keep_default_na=False,
).rename(columns={
    "cord_uid": "id_documento",
    "title": "titulo",
    "abstract": "resumo",
})


# ----- TRATAMENTO DE DOCUMENTOS DUPLICADOS -----
def primeiro_valor_preenchido(valores):
    """Usa o primeiro título ou resumo disponível na ordem do CSV."""
    
    return next((valor.strip() for valor in valores if valor.strip()), "")


def unir_identificadores(valores):
    """Combina IDs separados por ponto e vírgula, sem repeti-los."""
    
    identificadores = []
    for valor in valores:
        for identificador in valor.split(";"):
            identificador = identificador.strip()
            if identificador and identificador not in identificadores:
                identificadores.append(identificador)
    return ";".join(identificadores)


# Agrupa cada cord_uid em um documento e preserva referências das linhas repetidas.
documentos = (
    metadados_brutos.groupby("id_documento", sort=False, as_index=False)
    .agg({
        "titulo": primeiro_valor_preenchido,
        "resumo": primeiro_valor_preenchido,
        "sha": unir_identificadores,
        "pmcid": unir_identificadores,
    })
    .reindex(columns=["id_documento", "titulo", "resumo", "sha", "pmcid"])
)

# Associa os identificadores dos artigos aos arquivos completos disponíveis.
arquivos_pdf_por_identificador = {}
arquivos_pmc_por_identificador = {}

for caminho_json in sorted(pasta_colecao.rglob("*.json")):
    
    if caminho_json.parent.name == "pdf_json":
        identificador = caminho_json.stem
        arquivos_pdf_por_identificador.setdefault(identificador, []).append(caminho_json)
    
    elif caminho_json.parent.name == "pmc_json":
        # Os arquivos PMC usam nomes como PMC261870.xml.json.
        identificador = caminho_json.stem.removesuffix(".xml")
        arquivos_pmc_por_identificador.setdefault(identificador, []).append(caminho_json)


def localizar_arquivos_pdf(identificadores):
    """Localiza PDFs para todos os SHAs associados ao documento."""
    
    caminhos = []
    for identificador in identificadores.split(";"):
        identificador = identificador.strip()
        caminhos.extend(arquivos_pdf_por_identificador.get(identificador, []))
    return list(dict.fromkeys(caminhos))


def localizar_arquivos_pmc(identificadores):
    """Localiza arquivos PMC para todos os IDs associados ao documento."""
    
    caminhos = []
    for identificador in identificadores.split(";"):
        identificador = identificador.strip()
        caminhos.extend(arquivos_pmc_por_identificador.get(identificador, []))
    return list(dict.fromkeys(caminhos))


def ler_artigo(caminho_json):
    """Lê o JSON completo do artigo, preservando sua estrutura original."""
    
    with caminho_json.open(encoding="utf-8") as arquivo:
        return json.load(arquivo)

# O texto completo só é lido quando solicitado, sem carregar toda a coleção na RAM.
documentos["arquivos_pdf"] = documentos["sha"].map(localizar_arquivos_pdf)
documentos["arquivos_pmc"] = documentos["pmcid"].map(localizar_arquivos_pmc)


In [172]:
documentos

,id_documento,titulo,resumo,sha,pmcid,arquivos_pdf,arquivos_pmc
0,xqhn0vbp,Airborne rhinovirus detection and effect of ul...,"BACKGROUND: Rhinovirus, the most common cause ...",1e1286db212100993d03cc22374b624f7caee956,PMC140314,[/Users/apple/puc-minas/nlp/ho03-ranking-textu...,[/Users/apple/puc-minas/nlp/ho03-ranking-textu...
1,gi6uaa83,Discovering human history from stomach bacteria,Recent analyses of human pathogens have reveal...,8ae137c8da1607b3a8e4c946c07ca8bda67f88ac,PMC156578,[/Users/apple/puc-minas/nlp/ho03-ranking-textu...,[/Users/apple/puc-minas/nlp/ho03-ranking-textu...
2,le0ogx1s,A new recruit for the army of the men of death,"The army of the men of death, in John Bunyan's...",,PMC193621,[],[/Users/apple/puc-minas/nlp/ho03-ranking-textu...
3,fy4w7xz8,Association of HLA class I with severe acute r...,BACKGROUND: The human leukocyte antigen (HLA) ...,0104f6ceccf92ae8567a0102f89cbb976969a774,PMC212558,[/Users/apple/puc-minas/nlp/ho03-ranking-textu...,[/Users/apple/puc-minas/nlp/ho03-ranking-textu...
4,0qaoam29,A double epidemic model for the SARS propagation,BACKGROUND: An epidemic of a Severe Acute Resp...,5b68a553a7cbbea13472721cd1ad617d42b40c26,PMC222908,[/Users/apple/puc-minas/nlp/ho03-ranking-textu...,[/Users/apple/puc-minas/nlp/ho03-ranking-textu...
...,...,...,...,...,...,...,...
51040,4xhcamks,Prevalence of antibodies against transmissible...,Abstract Transmissible gastroenteritis (TGE) i...,e14e7f6ffed1a74954167e4fb52d1b2f156171cd,PMC7104163,[/Users/apple/puc-minas/nlp/ho03-ranking-textu...,[]
51041,z2rqz3jx,Can we increase public awareness without creat...,,9550137f5e105d2dbc14d91659a8c3cdd815c9b1,PMC7119035,[/Users/apple/puc-minas/nlp/ho03-ranking-textu...,[]
51042,wncuc903,Fast degrading polyesters as siRNA nano-carrie...,Abstract A potential siRNA carrier for pulmona...,2b3a3e3956afd65a8fa11d3867da3e58f8915514,PMC7125568,[/Users/apple/puc-minas/nlp/ho03-ranking-textu...,[]
51043,4x1ckr2i,eIF3f: A central regulator of the antagonism a...,Abstract The eukaryotic initiation factor 3 su...,a67dae6e5f2b58a6f16aaed4011c694f9e64dd88,PMC7108353,[/Users/apple/puc-minas/nlp/ho03-ranking-textu...,[]


Assim, se um documento não ter corpus em pdf, ele terá em pmc (xml) ou vice-versa. Por exemplo, no documento de índice 2, não tem pdf mas tem pmc. Ou no documento de indice 51040 que não tem pmc (xml) mas tem o corpus extraído do pdf. 

### **1.3. Consultas**


In [136]:
# Cada tópico do XML contém palavras-chave, uma pergunta e uma narrativa.
raiz_consultas = arvore_xml.parse(pasta_dados / "topics-rnd1.xml").getroot()
registros_consultas = []

for topico in raiz_consultas.findall("topic"):
    registros_consultas.append({
        "id_consulta": topico.attrib["number"],
        "consulta": topico.findtext("query", default=""),
        "pergunta": topico.findtext("question", default=""),
        "narrativa": topico.findtext("narrative", default=""),
    })

consultas = pd.DataFrame(registros_consultas)


In [137]:
consultas.head()

,id_consulta,consulta,pergunta,narrativa
0,1,coronavirus origin,what is the origin of COVID-19,seeking range of information about the SARS-Co...
1,2,coronavirus response to weather changes,how does the coronavirus respond to changes in...,seeking range of information about the SARS-Co...
2,3,coronavirus immunity,will SARS-CoV2 infected people develop immunit...,seeking studies of immunity developed due to i...
3,4,how do people die from the coronavirus,what causes death from Covid-19?,Studies looking at mechanisms of death from Co...
4,5,animal models of COVID-19,what drugs have been active against SARS-CoV o...,Papers that describe the results of testing d...


- **Consulta (query):** O que o usuário digita na barra de busca;

- **Pergunta (question):** O que o usuário realmente quer saber em linguagem natural completa;

- **Narrativa (narrative):** O manual de instruções pro avaliador humano, é uma regra para os avaliadores.

Via de regra, é utilizado apenas a **query** para construir o rankeamento de busca. Em alguns casos, utiliza-se a question junto com a query.

### **1.4. Julgamentos de relevância**


In [138]:
# O arquivo não tem cabeçalho e suas colunas são separadas por espaços.
# Relevância: 0 = não relevante, 1 = parcialmente relevante, 2 = relevante.
julgamentos = pd.read_csv(
    pasta_dados / "qrels-rnd1.txt",
    sep=r"\s+",
    names=["id_consulta", "rodada", "id_documento", "relevancia"],
    dtype={"id_consulta": str, "rodada": str, "id_documento": str, "relevancia": int},
    keep_default_na=False,
)


In [139]:
julgamentos.head()

,id_consulta,rodada,id_documento,relevancia
0,1,0.5,010vptx3,2
1,1,1,02f0opkr,1
2,1,1,04ftw7k9,0
3,1,1,05qglt1f,0
4,1,1,0604jed8,0


tem 8.691 julgamentos, se dividir por 30 consultas, é como se tivessem avaliado uns 290 documentos por query apenas

### **1.5. Conferência da carga e dos IDs únicos**


In [140]:
assert documentos["id_documento"].is_unique

print(f"Linhas no metadata.csv: {len(metadados_brutos):,}")
print(f"Documentos únicos por cord_uid: {len(documentos):,}")
print(f"Linhas excedentes consolidadas: {len(metadados_brutos) - len(documentos):,}")
print(f"Consultas: {len(consultas):,}")
print(f"Julgamentos: {len(julgamentos):,}")


Linhas no metadata.csv: 51,078
Documentos únicos por cord_uid: 51,045
Linhas excedentes consolidadas: 33
Consultas: 30
Julgamentos: 8,691


- 51.078 metadados de papers;
- 33 são duplicados;
- 51.045 são artigos deduplicados;
- 8.691 notas humanas, todos fora desse gabarito são de relevância 0;
- 30 querys;

## **2. Inspeção dos textos completos**

Vamos observar um mesmo artigo nas versões PDF e PMC. Comparar o título, as seções e os parágrafos. A ideia é entender como os arquivos representam o artigo antes de decidir qual versão usar no ranking.


In [141]:
# Escolhe um registro com exatamente um arquivo de cada formato,
# para que a comparação seja simples de acompanhar.
documentos_com_uma_versao_de_cada = documentos.loc[
    documentos["arquivos_pdf"].map(len).eq(1)
    & documentos["arquivos_pmc"].map(len).eq(1)
]

amostra_documento = documentos_com_uma_versao_de_cada.iloc[0]
print("ID:", amostra_documento["id_documento"])
print("Título:", amostra_documento["titulo"])

for nome_formato, caminho_json in [
    ("PDF", amostra_documento["arquivos_pdf"][0]),
    ("PMC", amostra_documento["arquivos_pmc"][0]),
]:
    artigo = ler_artigo(caminho_json)
    paragrafos = artigo.get("body_text", [])

    print(f"\n--- Versão {nome_formato} ---")
    print("Parágrafos no corpo:", len(paragrafos))
    for paragrafo in paragrafos[:2]:
        print("Seção:", paragrafo.get("section") or "(sem nome)")
        print("Texto:", paragrafo.get("text", "")[:300])


ID: xqhn0vbp
Título: Airborne rhinovirus detection and effect of ultraviolet irradiation on detection by a semi-nested RT-PCR assay

--- Versão PDF ---
Parágrafos no corpo: 33
Seção: Background
Texto: Rhinoviruses have been associated with 40% to 65% of "common colds" studied by methods of virus culture [1, 2] . With the use of reverse transcriptase -polymerase chain reaction (RT-PCR), rhinovirus has been shown to be associated with 53% of all colds throughout the year and up to 92% of colds duri
Seção: Background
Texto: Although rhinoviruses have been thought to be transmitted via large droplets or contact [7] , studies in the 1980's demonstrated that fomites are not an effective means of transmitting rhinovirus infections [8] [9] [10] . While direct inoculation of respiratory secretions has been shown to transmit 

--- Versão PMC ---
Parágrafos no corpo: 41
Seção: Background
Texto: Rhinoviruses have been associated with 40% to 65% of "common colds" studied by methods of virus culture

**Critério adotado:** preferir a versão PMC; se não houver, usar PDF. Se nenhum texto completo estiver disponível, usar título e resumo do CSV. Assim evitamos contar duas versões do mesmo artigo no ranking.


In [142]:
def obter_texto_documento(documento):
    """
    Retorna o texto do documento:
    1. Prioriza PMC
    2. Se não houver, usa PDF
    3. Se não houver nenhum, fica com título e resumo
    """
    
    # 1. Começa com o título e resumo
    partes = [documento["titulo"], documento["resumo"]]
    
    # 2. Descobre qual arquivo abrir
    caminho_artigo = None
    fonte = "metadados"
    
    if documento["arquivos_pmc"]:
        caminho_artigo = documento["arquivos_pmc"][0]
        fonte = "PMC"
    elif documento["arquivos_pdf"]:
        caminho_artigo = documento["arquivos_pdf"][0]
        fonte = "PDF"
        
    # 3. Se tiver arquivo, lê e acrescenta os parágrafos do corpo
    if caminho_artigo is not None:
        artigo = ler_artigo(caminho_artigo)
        for paragrafo in artigo.get("body_text", []):
            texto = paragrafo.get("text", "").strip()
            if texto:
                partes.append(texto)
                
    # 4. Junta tudo em um texto só
    return " ".join(partes), fonte

Ou seja, diferente da lib ir_dataset, aqui acrescentei o texto do artigo além de apenas o resumo e título quando houver.

Agora, vamos ver se a hierarquia de busca tá funcionando:

In [143]:
for descricao, documento in exemplos_texto:
    texto_documento, fonte_escolhida = obter_texto_documento(documento)
    print(
        f"{descricao}: fonte={fonte_escolhida}, "
        f"caracteres={len(texto_documento):,}"
    )

PMC e PDF: fonte=PMC, caracteres=22,833
Somente PDF: fonte=PDF, caracteres=11,487
Somente metadados: fonte=metadados, caracteres=1,264


## **4. Pré-processamento**

As etapas serão:

1. Normalização
2. Remoção de acentuação
3. Tokenização
4. Remoção de Stopwords
5. Stemming

### 4.1. Normalização

In [144]:
import re

def normalizar(texto: str):
    """
    Normaliza um texto de input da seguinte forma:

    1. Deixa em minusculo
    2. Trata termos específicos da doença
    """

    # 1. Deixar tudo em mínusculo.
    texto = texto.lower()

    # 2. Utiliza regex para encontrar variantes de covid ou sars cov.
    texto = re.sub(r"\bcovid[\s-]*19\b", "covid19", texto)
    texto = re.sub(r"\bsars[\s-]*cov[\s-]*2\b", "sarscov2", texto)
    
    return texto

tudo em mínusculo.

### 4.2. Remoção de Acentuação

In [145]:
import unicodedata

def remover_acentos(texto: str):

    # 1. Decompõe as acentuações e remove elas.
    texto_nfkd = unicodedata.normalize("NFKD", texto)
    
    return "".join(c for c in texto_nfkd if not unicodedata.combining(c))


In [146]:
# teste.
remover_acentos("naïve")

'naive'

remoção de acentuação feita

### 4.3. Tokenização

In [147]:
import re

def tokenizar(texto: str) -> list[str]:
    # Extrai palavras e números, ignorando pontuação (sem o bug de timeout do NLTK)
    return re.findall(r"\w+", texto)

### 4.4. Remoção de Stopwords

In [148]:
import nltk
nltk.download('stopwords')
from nltk.corpus import stopwords

# 1. Stopwords do NLTK em inglês
lista_stopwords = set(stopwords.words('english'))

negacoes = {"no", "not", "nor", "neither", "never", "none", "without"}

# 2. Preservamos as negações pro contexto médico.
stopwords_filtradas = lista_stopwords - negacoes

[nltk_data] Downloading package stopwords to /Users/apple/nltk_data...
[nltk_data]   Package stopwords is already up-to-date!


In [149]:
def remover_stopwords(tokens: list[str]) -> list[str]:
    """
    Remove as stopwords de uma lista de tokens (documento tokenizado)
    """

    return [token for token in tokens if token not in stopwords_filtradas]

### 4.5. Stemming

In [150]:
from nltk.stem import PorterStemmer

stemmer = PorterStemmer()

def aplicar_stemming(tokens: list[str]) -> list[str]:
    """
    Aplica a Stemmatização nos tokens para tirar a flexão.
    """

    return [stemmer.stem(token) for token in tokens]

### 4.6. Pipeline Unificado

In [151]:
def preprocessar(texto: str) -> list[str]:
    texto = normalizar(texto)
    texto = remover_acentos(texto)
    tokens = tokenizar(texto)
    tokens = remover_stopwords(tokens)
    tokens = aplicar_stemming(tokens)
    return tokens

In [152]:
# Testar.
exemplo = "The naïve patients were NOT without COVID-19 infections!"
print("Antes: ", exemplo)
print("Depois:", preprocessar(exemplo))

Antes:  The naïve patients were NOT without COVID-19 infections!
Depois: ['naiv', 'patient', 'not', 'without', 'covid19', 'infect']


Com o pipeline de pré-processamento aplicado, podemos primeiro aplicar o mesmo pipe nas querys

In [153]:
consultas["tokens"] = consultas["consulta"].apply(preprocessar)

In [154]:
consultas.head()

,id_consulta,consulta,pergunta,narrativa,tokens
0,1,coronavirus origin,what is the origin of COVID-19,seeking range of information about the SARS-Co...,"[coronaviru, origin]"
1,2,coronavirus response to weather changes,how does the coronavirus respond to changes in...,seeking range of information about the SARS-Co...,"[coronaviru, respons, weather, chang]"
2,3,coronavirus immunity,will SARS-CoV2 infected people develop immunit...,seeking studies of immunity developed due to i...,"[coronaviru, immun]"
3,4,how do people die from the coronavirus,what causes death from Covid-19?,Studies looking at mechanisms of death from Co...,"[peopl, die, coronaviru]"
4,5,animal models of COVID-19,what drugs have been active against SARS-CoV o...,Papers that describe the results of testing d...,"[anim, model, covid19]"


**Observação:** Aqui tem um problema, se eu rodar por exemplo o pré-processamento com .apply() do pandas em 51k de documentos vai ficar inviável, esse método do pandas é muito mal otimizado pra grandes volumes de dados.

Vai estourar a memória ram do meu computador...

Pra resolver, vou usar o método de pegar 1 documento por vez do disco e pré-processar.

In [155]:
from joblib import Parallel, delayed
from tqdm import tqdm
from collections import Counter

# 1. Indice Invertido (otimização para dados volumosos)
indice_invertido = {}

# 2. Tamanho dos Documentos.
tamanho_documentos = {}

# Função isolada que roda em paralelo em cada núcleo do M1 Pro
def processar_um_documento(documento):
    # Obtém o ID do documento.
    doc_id = documento["id_documento"]

    # Pega o corpus do documento no disco.
    corpus, fonte = obter_texto_documento(documento)

    # Aplica o pipeline de pré-processamento no corpus.
    tokens = preprocessar(corpus)

    # Guarda o tamanho do vocabulário do documento.
    tamanho = len(tokens)

    # Conta a frequência de cada token nesse corpus.
    contagem_palavras = Counter(tokens)

    return doc_id, tamanho, contagem_palavras

# Transforma os documentos em lista de registros para distribuir entre os núcleos
lista_documentos = documentos.to_dict(orient="records")

# n_jobs=-1 usa TODOS os núcleos do seu M1 Pro ao mesmo tempo!
# return_as="generator" entrega o resultado assim que cada núcleo termina, sem gastar RAM
resultados_paralelos = Parallel(n_jobs=-1, batch_size=64, return_as="generator")(
    delayed(processar_um_documento)(doc) for doc in lista_documentos
)

# Cria uma barra de progressão e utiliza os resultados processados em paralelo
for doc_id, tamanho, contagem_palavras in tqdm(resultados_paralelos, total=len(lista_documentos), desc="Indexando Artigos (M1 Pro)"):

    # Guarda o tamanho do vocabulário do documento.
    tamanho_documentos[doc_id] = tamanho

    # Coloca no índice invertido.
    for termo, frequencia in contagem_palavras.items():
        if termo not in indice_invertido:
            indice_invertido[termo] = {} # Se ainda não existe no índice invertido.

        indice_invertido[termo][doc_id] = frequencia

Indexando Artigos (M1 Pro): 100%|██████████| 51045/51045 [02:07<00:00, 400.40it/s] 


Com o **índice invertido** a gente escapa de uma ordem de grandeza elevada ao quadrado. Por exemplo, se eu fosse buscar um termo no conjunto original de documentos, na minha cabeça seria (isso pensando no pior caso):

- N iterações entre 51k de documentos para contagem de um termo específico;

- N iterações de tokens/palavras dentro de um corpus de um documento para contabilizar o token buscado.

**O(nˆ2)**

Se a gente faz o índice invertido (que tem no capítulo 11 do livro de referência), temos O(1) na busca, pq temos um dicionário:

```
indice_invertido = {

    "infect": {
        documento_1: 1, 
        documento_4: 15,
        documento_XYZ: 999}
}
```

Acessamos um termo direto e conseguimos contabilizar sua frequência de forma rápida.

In [ ]:
# import pickle

# with open("indice_invertido.pkl", "wb") as f:
#    pickle.dump(indice_invertido, f)

# with open("tamanho_documentos.pkl", "wb") as f:
#    pickle.dump(tamanho_documentos, f)

# print(f"✓ Índice salvo! Vocabulário total: {len(indice_invertido):,} termos únicos.")

✓ Índice salvo! Vocabulário total: 919,661 termos únicos.


Salvei em arquivo *.pkl* pra não ficar reprocessando a indexação toda vez que eu rodar de novo, mesmo utilizando os cores na paralelização.

Quase 1 milhão de tokens no dicionário de índice invertido. Agora que temos a frequência de tokens em cada documento e a quantidade, podemos iniciar a criação do objetivo da atividade.

In [157]:
import pickle
from pathlib import Path

# Checkpoint.

# Localiza os arquivos caso você esteja na raiz do projeto ou dentro da pasta notebooks/
pasta_atual = Path.cwd().resolve()
caminho_indice = pasta_atual / "indice_invertido.pkl" if (pasta_atual / "indice_invertido.pkl").exists() else pasta_atual.parent / "indice_invertido.pkl"
caminho_tamanhos = pasta_atual / "tamanho_documentos.pkl" if (pasta_atual / "tamanho_documentos.pkl").exists() else pasta_atual.parent / "tamanho_documentos.pkl"

# 1. Carrega o Índice Invertido
with open(caminho_indice, "rb") as f:
    indice_invertido = pickle.load(f)

# 2. Carrega o dicionário de tamanhos dos documentos
with open(caminho_tamanhos, "rb") as f:
    tamanho_documentos = pickle.load(f)

print(f"✓ Índice carregado com sucesso! {len(indice_invertido):,} termos únicos.")
print(f"✓ Tamanhos carregados com sucesso! {len(tamanho_documentos):,} documentos mapeados.")

✓ Índice carregado com sucesso! 919,661 termos únicos.
✓ Tamanhos carregados com sucesso! 51,045 documentos mapeados.


In [158]:
indice_invertido

{'airborn': {'xqhn0vbp': 17,
  '0fitbwuv': 1,
  'ndnze5o4': 9,
  'fghu8ouc': 3,
  'v09jj3a2': 1,
  '124czudi': 3,
  'nzh87aux': 1,
  'nada82w4': 1,
  'kfwbqp4p': 1,
  'jj0juopc': 1,
  'umvrwgaw': 2,
  '4z38v9rg': 1,
  '2nko37oo': 1,
  'nj19fiqr': 10,
  '22lf1cp5': 1,
  '7222okvv': 2,
  'qww6pe61': 2,
  '8em6kpwk': 1,
  '1j8z8lak': 1,
  'xceg0iz9': 2,
  'mz0j6jdv': 1,
  'kkh04kv8': 1,
  '7a55odok': 1,
  'kj3ptk7x': 1,
  'bhnh2dq4': 2,
  '96migwaq': 3,
  'out6zg61': 1,
  'a71k778s': 1,
  '8ksyhbig': 7,
  'fcwxyco2': 1,
  'hwjkbpqp': 1,
  '36bfeoqv': 2,
  'zuvy8htp': 1,
  'dxo8l9gu': 2,
  'tjdxn29l': 3,
  'b5yl88mh': 1,
  '7ofqlw6w': 4,
  'c1uefp15': 1,
  '506e85m9': 12,
  'xroo7z7g': 1,
  'i7navmbn': 6,
  'evgw0as5': 2,
  'awx8rcal': 1,
  'q0ln8a1l': 1,
  'fxre60s9': 1,
  'p02mvtm1': 8,
  '548yclab': 2,
  'f7ky61ds': 1,
  'nhvftcvo': 1,
  '8seknsaq': 3,
  'olcuq6tm': 6,
  '6z2avwqx': 1,
  'qjmyc2tu': 2,
  'grmef7ab': 2,
  '91lzomwp': 1,
  '4tsynits': 1,
  'eva0soja': 1,
  'ntv2veww': 19,

## **5. TF-IDF**

O TF-IDF é bem simples de entender:

- O **TF** vai literalmente contar a frequência de um token em um documento. Ele já está pronto no índice invertido, seria cada chave e a frequência em um documento seria o objeto chave-valor dentro.

Ex:

```
{'airborn': {'xqhn0vbp': 17,
  '0fitbwuv': 1,
  'ndnze5o4': 9,
  'fghu8ouc': 3,
```

airborn seria o token, o TF dele no documento xqhn0vbp seria: TF(airborn, xqhn0vbp) = 17

O IDF vai medir a raridade de um token no mundo, pra isso, contamos:

- Quantos documentos esse token aparece (DF);
- Divide o total de documentos por essa frequência: N/DF;

Ai se resulta em um valor maior, significa que o termo é mais raro (denominador pequeno), o posto indica que é um termo comum.

Só que se um termo aparece uma vez, o peso seria **muito maior**, ai aplica-se um logaritmo pra suavizar a escala desses termos.

**IDF -> ln(N/DF(t))**

In [159]:
import math


# -- TESTE --

# Total de artigos da base:
N = len(tamanho_documentos)

for palavra in ['coronaviru', 'origin', 'patient']:
    if palavra in indice_invertido:

        # Calcular o DF -> quantos documentos tem o termo.
        df = len(indice_invertido[palavra])

        # IDF.
        idf = math.log(N/df)

        print(f"Palavra: '{palavra:<12}' | Aparece em: {df:>5} artigos | IDF: {idf:.3f}")

Palavra: 'coronaviru  ' | Aparece em: 23827 artigos | IDF: 0.762
Palavra: 'origin      ' | Aparece em: 17536 artigos | IDF: 1.068
Palavra: 'patient     ' | Aparece em: 22146 artigos | IDF: 0.835


Dá pra ver que a palavra origin é mais **rara**, logo, seu IDF será maior, seu peso é maior.

Para calcular a pontuação de um documento em relação a uma consulta, combinamos a frequência local do termo (**TF**) com a sua raridade global (**IDF**):

1. **Peso do termo na consulta ($w_{t, q}$):**  
   Como a consulta é curta (o termo geralmente aparece 1 vez nela), o peso do termo na consulta é proporcional ao seu IDF:
   $$w_{t, q} = 1 \times \text{IDF}(t)$$

2. **Peso do termo no documento ($w_{t, d}$):**  
   É o produto de quantas vezes o termo apareceu naquele documento pelo seu IDF:
   $$w_{t, d} = \text{TF}(t, d) \times \text{IDF}(t)$$

3. **O Produto Escalar ($\vec{q} \cdot \vec{d}$):**  
   Ao multiplicarmos o peso da consulta pelo peso do documento para cada termo em comum:
   $$w_{t, q} \times w_{t, d} = \text{IDF}(t) \times \big(\text{TF}(t, d) \times \text{IDF}(t)\big) = \mathbf{\text{TF}(t, d) \times \text{IDF}(t)^2}$$

> **Por que aparece $\text{IDF}^2$?**  
> O fator de raridade (IDF) entra **duas vezes** no cálculo: uma vez para ponderar a especificidade do termo na pergunta e outra vez para ponderar a relevância do termo no documento.

Sem uma normalização, documentos muito longos (ex: artigos de 50 páginas) levariam uma vantagem injusta sobre documentos curtos e objetivos (ex: artigos de 2 páginas), simplesmente porque textos longos acumulam mais contagens de palavras.

Para equilibrar a disputa, a **Similaridade do Cosseno** divide a pontuação acumulada pela raiz quadrada do tamanho total do documento:

$$\text{Score}(q, d) = \frac{\sum_{t \in q} \text{TF}(t, d) \times \text{IDF}(t)^2}{\sqrt{|d|}}$$
Onde:

* $\text{TF}(t, d)$: Frequência do termo $t$ no documento $d$ 
(armazenado no `indice_invertido`).

* $\text{IDF}(t) = \ln\left(\frac{N}{\text{DF}(t)}\right)$: Raridade global do termo na coleção.

* $|d|$: Tamanho total do documento em palavras (armazenado em `tamanho_documentos[doc_id]`).

(Copiei do Gemini - Gostei da explicação.)

In [160]:
# Com essa explicação, dá para fazer o ranqueamento TF-IDF na mão.
from collections import defaultdict

# 1. Total de documentos da base.
QTD_DOCUMENTOS = len(tamanho_documentos)


def ranqueamento_tfidf(query: list[str]) -> list[tuple[str, float]]:
    """
    Realiza o ranqueamento utilizando o modelo vetorial TF-IDF.

    Recebe:

        - Uma query pré-processada e tokenizada.
    
    Retorna:

        - Uma lista que contém tupla (documento, score)
    """

    scores = defaultdict(float)

    for token in query:
        if token in indice_invertido:

            # Calcula o DF.
            df = len(indice_invertido[token])

            # Calcula o IDF (raridade).
            idf = math.log(QTD_DOCUMENTOS / df)

            # Para o token iterado: itere sobre cada documento que ele existe e a sua frequência.
            for doc_id, tf in indice_invertido[token].items():
                scores[doc_id] += tf * (idf ** 2)


    # Agora, temos um dicionário scores, mas ainda é preciso normalizar cada score
    for doc_id in scores:
        tamanho = tamanho_documentos.get(doc_id, 1)
        scores[doc_id] /= math.sqrt(tamanho)

    # Agora, basta ordenar o maior score para o menor.
    ranking_ordenado = sorted(scores.items(), key=lambda item: item[1], reverse=True)

    return ranking_ordenado 

Com a função de ranqueamento TF-IDF implementada, podemos fazer uma consulta de teste só pra visualizar o ranking.

In [ ]:
import pandas as pd

def visualizar_resultado_tfidf(id_consulta: str, top_k: int = 10):
    """
    Executa o TF-IDF para uma consulta e monta uma tabela visual comparando
    o resultado do algoritmo com a nota oficial dada pelos médicos no gabarito.
    """
    
    # 1. Pega os dados da consulta
    linha_consulta = consultas.loc[consultas["id_consulta"] == str(id_consulta)].iloc[0]
    tokens = linha_consulta["tokens"]
    texto_busca = linha_consulta["consulta"]
    
    print(f"=== Consulta {id_consulta}: '{texto_busca}' ===")
    print(f"Tokens usados: {tokens}\n")
    
    # 2. Executa o TF-IDF
    ranking = ranqueamento_tfidf(tokens)
    
    # 3. Filtra as notas dos médicos apenas para esta consulta
    notas_consulta = julgamentos.loc[julgamentos["id_consulta"] == str(id_consulta)].set_index("id_documento")["relevancia"].to_dict()
    
    # 4. Monta a tabela dos Top K
    tabela_resultados = []
    for posicao, (doc_id, score) in enumerate(ranking[:top_k], start=1):
        # Busca o título
        filtro_doc = documentos.loc[documentos["id_documento"] == doc_id]
        titulo = filtro_doc["titulo"].iloc[0] if not filtro_doc.empty else "(Sem título)"
        
        # Busca a nota oficial dos médicos (se não estiver nos qrels, é 0)
        nota_medica = notas_consulta.get(doc_id, 0)
        legenda_nota = {0: "0 (Não relevante)", 1: "1 (Parcial)", 2: "2 (Altamente relevante)"}.get(nota_medica, "0")
        
        tabela_resultados.append({
            "Posição": f"{posicao}º",
            "Score TF-IDF": round(score, 4),
            "Nota dos Médicos": legenda_nota,
            "ID Documento": doc_id,
            "Título do Artigo": titulo
        })
        
    return pd.DataFrame(tabela_resultados)

In [164]:
visualizar_resultado_tfidf("30", top_k=10)

=== Consulta 30: 'coronavirus remdesivir' ===
Tokens usados: ['coronaviru', 'remdesivir']



,Posição,Score TF-IDF,Nota dos Médicos,ID Documento,Título do Artigo
0,1º,39.7569,2 (Altamente relevante),9hxihlw9,Arguments in favour of remdesivir for treating...
1,2º,34.6361,1 (Parcial),uc3slu8q,Remdesivir inhibits renal fibrosis in obstruct...
2,3º,33.8116,2 (Altamente relevante),95fc828i,Current knowledge about the antivirals remdesi...
3,4º,30.7124,0 (Não relevante),rn3bjc9d,Mechanism of Inhibition of Ebola Virus RNA-Dep...
4,5º,28.2991,2 (Altamente relevante),b518n9dx,Remdesivir for severe acute respiratory syndro...
5,6º,27.6154,1 (Parcial),x50tvq3a,Prophylactic and therapeutic remdesivir (GS-57...
6,7º,25.5204,2 (Altamente relevante),1hwdd7nq,Remdesivir as a possible therapeutic option fo...
7,8º,14.4106,1 (Parcial),7e8zlt3t,"Remdesivir, lopinavir, emetine, and homoharrin..."
8,9º,11.6945,2 (Altamente relevante),6wbrv9o1,Clinical and virological data of the first cas...
9,10º,10.9575,1 (Parcial),r22x7gnu,Remdesivir and chloroquine effectively inhibit...


Perceba que isso é só para uma única consulta de teste. Precisamos aplicar um ranqueamento para as 30 consultas em relação à 51k de documentos.

São aproximadamente 1.5M de pares, talvez seja interessante paralelizar essas operações também.

## **6. Ranking com BM25**

Para uma consulta composta pelos termos $q_1, q_2, \dots, q_n$, a pontuação de relevância de um documento $D$ é dada por:

$$\text{BM25}(D, Q) = \sum_{t \in Q} \text{IDF}(t) \cdot \frac{\text{TF}(t, D) \cdot (k_1 + 1)}{\text{TF}(t, D) + k_1 \cdot \left(1 - b + b \cdot \frac{|D|}{\text{avgdl}}\right)}$$

Onde cada componente desempenha um papel específico:

- **$\text{TF}(t, D)$ e o parâmetro $k_1 = 1.5$ (Saturação de Frequência):**  
  Controla a rapidez com que a pontuação satura conforme o termo se repete. Conforme a frequência $\text{TF}$ cresce, a fração se aproxima assintoticamente de $(k_1 + 1)$. Isso significa que a primeira ocorrência da palavra vale muito; a segunda vale um pouco menos; e a vigésima quase não acrescenta pontuação, impedindo que textos prolixos monopolizem o ranking. O valor $1.5$ é o padrão canônico da literatura.

- **$|D|$, $\text{avgdl}$ e o parâmetro $b = 0.75$ (Normalização de Comprimento):**  
  Compara o tamanho do documento atual ($|D|$) com o tamanho médio de todos os documentos da base ($\text{avgdl} \approx 2.395$ tokens na nossa coleção). O parâmetro $b$ calibra o impacto dessa penalidade:

  - Se $b = 1$, a penalidade de tamanho é proporcional e máxima.

  - Se $b = 0$, o tamanho do documento é completamente ignorado.

  - O valor $0.75$ estabelece um equilíbrio ideal para textos científicos, exigindo que artigos muito longos tenham uma concentração maior do termo para merecerem as primeiras posições.

- **$\text{IDF}(t)$ (Raridade Probabilística):**  
  Adotamos a formulação probabilística não-negativa padrão do Lucene:

  $$\text{IDF}(t) = \ln\left(\frac{N - \text{DF}(t) + 0.5}{\text{DF}(t) + 0.5} + 1\right)$$

  Essa formulação garante que termos raros (como nomes de medicamentos específicos) tenham peso elevado, sem o risco de gerar pontuações negativas para termos muito comuns.

  (Copiado do Gemini)

In [163]:
# 1. Total de documentos e média de tamanho da base
QTD_DOCUMENTOS = len(tamanho_documentos)
AVGDL = sum(tamanho_documentos.values()) / QTD_DOCUMENTOS


def ranqueamento_bm25(
    query: list[str], k1: float = 1.5, b: float = 0.75
) -> list[tuple[str, float]]:
  """Realiza o ranqueamento utilizando o algoritmo Okapi BM25.

  Recebe:
      - query: Lista de tokens pré-processados.
      - k1: Parâmetro de saturação do TF (padrão 1.5).
      - b: Parâmetro de normalização do tamanho do documento (padrão 0.75).

  Retorna:
      - Lista de tuplas ordenadas (id_documento, score_bm25) em ordem
      decrescente.
  """
  scores = defaultdict(float)

  for token in query:
    if token in indice_invertido:
      # DF: quantidade de documentos que possuem o termo
      df = len(indice_invertido[token])

      # IDF probabilístico não-negativo (Robertson / Lucene BM25)
      idf = math.log((QTD_DOCUMENTOS - df + 0.5) / (df + 0.5) + 1.0)

      # Itera apenas sobre os documentos que contêm o termo
      for doc_id, tf in indice_invertido[token].items():
        tamanho_doc = tamanho_documentos.get(doc_id, AVGDL)

        # Equação do BM25
        numerador = tf * (k1 + 1.0)
        denominador = tf + k1 * (1.0 - b + b * (tamanho_doc / AVGDL))

        scores[doc_id] += idf * (numerador / denominador)

  # Ordena do maior score para o menor
  return sorted(scores.items(), key=lambda item: item[1], reverse=True)

In [165]:
def visualizar_resultado_bm25(id_consulta: str, top_k: int = 10):
  """Executa o BM25 para uma consulta e monta uma tabela comparando

  o resultado do algoritmo com a nota oficial dos médicos.
  """
  linha_consulta = consultas.loc[
      consultas["id_consulta"] == str(id_consulta)
  ].iloc[0]
  tokens = linha_consulta["tokens"]
  texto_busca = linha_consulta["consulta"]

  print(f"=== Consulta {id_consulta} (BM25): '{texto_busca}' ===")
  print(f"Tokens usados: {tokens}\n")

  ranking = ranqueamento_bm25(tokens)
  notas_consulta = (
      julgamentos.loc[julgamentos["id_consulta"] == str(id_consulta)]
      .set_index("id_documento")["relevancia"]
      .to_dict()
  )

  tabela_resultados = []
  for posicao, (doc_id, score) in enumerate(ranking[:top_k], start=1):
    filtro_doc = documentos.loc[documentos["id_documento"] == doc_id]
    titulo = (
        filtro_doc["titulo"].iloc[0] if not filtro_doc.empty else "(Sem título)"
    )
    nota_medica = notas_consulta.get(doc_id, 0)
    legenda_nota = {
        0: "0 (Não relevante)",
        1: "1 (Parcial)",
        2: "2 (Altamente relevante)",
    }.get(nota_medica, "0")

    tabela_resultados.append({
        "Posição": f"{posicao}º",
        "Score BM25": round(score, 4),
        "Nota dos Médicos": legenda_nota,
        "ID Documento": doc_id,
        "Título do Artigo": titulo,
    })

  return pd.DataFrame(tabela_resultados)

In [166]:
visualizar_resultado_bm25("30", top_k=10)

=== Consulta 30 (BM25): 'coronavirus remdesivir' ===
Tokens usados: ['coronaviru', 'remdesivir']



,Posição,Score BM25,Nota dos Médicos,ID Documento,Título do Artigo
0,1º,15.0097,2 (Altamente relevante),9hxihlw9,Arguments in favour of remdesivir for treating...
1,2º,14.8900,2 (Altamente relevante),b518n9dx,Remdesivir for severe acute respiratory syndro...
2,3º,14.7888,1 (Parcial),uc3slu8q,Remdesivir inhibits renal fibrosis in obstruct...
3,4º,14.6912,2 (Altamente relevante),95fc828i,Current knowledge about the antivirals remdesi...
4,5º,14.6210,2 (Altamente relevante),1hwdd7nq,Remdesivir as a possible therapeutic option fo...
5,6º,14.6000,1 (Parcial),x50tvq3a,Prophylactic and therapeutic remdesivir (GS-57...
6,7º,14.4745,1 (Parcial),7e8zlt3t,"Remdesivir, lopinavir, emetine, and homoharrin..."
7,8º,14.1932,1 (Parcial),r22x7gnu,Remdesivir and chloroquine effectively inhibit...
8,9º,14.0394,1 (Parcial),bw9lbzvt,Characterization and treatment of SARS-CoV-2 i...
9,10º,14.0212,2 (Altamente relevante),6wbrv9o1,Clinical and virological data of the first cas...


O BM25 na consulta de visualização, que foi a 30 escolhida, já tem um resultado bem melhor que no TF-IDF.

## **Aplicando Ranking TF-IDF + BM25 em todos os Docs**

In [168]:
# Mapeia as 30 consultas com seus tokens pré-processados
dicionario_consultas = dict(zip(consultas["id_consulta"], consultas["tokens"]))

# Executa TF-IDF e BM25 para todas as 30 consultas (leva ~5 segundos)
rankings_tfidf = {
    qid: ranqueamento_tfidf(tokens)
    for qid, tokens in dicionario_consultas.items()
}
rankings_bm25 = {
    qid: ranqueamento_bm25(tokens)
    for qid, tokens in dicionario_consultas.items()
}

print(f"Rankings gerados para as {len(rankings_tfidf)} consultas!")

Rankings gerados para as 30 consultas!


## **Métricas e Conclusões**

In [169]:
from ranx import Qrels, Run, evaluate

# 1. Transforma o dataframe `julgamentos` no formato que o ranx lê
gabarito_dict = defaultdict(dict)
for _, linha in julgamentos.iterrows():
  gabarito_dict[str(linha["id_consulta"])][str(linha["id_documento"])] = int(
      linha["relevancia"]
  )

qrels = Qrels(gabarito_dict)

# 2. Roda as funções de busca para as 30 consultas e passa para o ranx
dicionario_consultas = dict(zip(consultas["id_consulta"], consultas["tokens"]))

run_tfidf = Run(
    {
        qid: dict(ranqueamento_tfidf(tokens)[:1000])
        for qid, tokens in dicionario_consultas.items()
    },
    name="TF-IDF",
)
run_bm25 = Run(
    {
        qid: dict(ranqueamento_bm25(tokens)[:1000])
        for qid, tokens in dicionario_consultas.items()
    },
    name="BM25",
)

# 3. Chama a função pronta do ranx para calcular o MAP nos cortes solicitados
metricas_map = ["map@1", "map@3", "map@5", "map@10", "map"]

resultado_tfidf = evaluate(qrels, run_tfidf, metricas_map)
resultado_bm25 = evaluate(qrels, run_bm25, metricas_map)

In [ ]:
# 1. Lista completa com todas as métricas
todas_metricas = [
    # MAP
    "map@1",
    "map@3",
    "map@5",
    "map@10",
    "map",
    # nDCG
    "ndcg@1",
    "ndcg@3",
    "ndcg@5",
    "ndcg@10",
    "ndcg",
]

# 2. Avaliação direta com o ranx
resultado_tfidf = evaluate(qrels, run_tfidf, todas_metricas)
resultado_bm25 = evaluate(qrels, run_bm25, todas_metricas)

# 3. Mapeamento dos nomes para exibição
nomes_exibicao = {
    "map@1": "MAP @1",
    "map@3": "MAP @3",
    "map@5": "MAP @5",
    "map@10": "MAP @10",
    "map": "MAP Geral",
    "ndcg@1": "nDCG @1",
    "ndcg@3": "ndcg @3",
    "ndcg@5": "ndcg @5",
    "ndcg@10": "ndcg @10",
    "ndcg": "ndcg Geral",
}

# 4. Monta a tabela final unificada
linhas_finais = []
for m in todas_metricas:
  tf = resultado_tfidf[m]
  bm = resultado_bm25[m]
  ganho = ((bm - tf) / tf) * 100 if tf > 0 else 0.0

  linhas_finais.append({
      "Métrica": nomes_exibicao[m],
      "TF-IDF": round(tf, 4),
      "BM25": round(bm, 4),
      "Diferença": f"+{ganho:.1f}%",
  })

df_comparativo_final = pd.DataFrame(linhas_finais)
df_comparativo_final

,Métrica,TF-IDF,BM25,Diferença
0,MAP @1,0.0024,0.0126,+431.9%
1,MAP @3,0.0104,0.0303,+190.5%
2,MAP @5,0.0139,0.0432,+211.5%
3,MAP @10,0.0274,0.0719,+162.6%
4,MAP Geral,0.1339,0.2239,+67.2%
5,nDCG @1,0.1333,0.5833,+337.5%
6,ndcg @3,0.1981,0.5362,+170.6%
7,ndcg @5,0.1799,0.4865,+170.4%
8,ndcg @10,0.1966,0.4594,+133.7%
9,ndcg Geral,0.3791,0.5140,+35.6%


**Conclusão**

A partir da tabela comparativa das métricas de recuperação de informação, dá para observar que:

- O BM25 foi bem mais expressivo do que a abordagem TF-IDF em todos os pontos de corte e também nos rankings gerais.

Isso significa que, um usuário ao fazer uma consulta ele tende a ler só os primeiros resultados da pesquisa, logo, o BM25 entrega isso de forma facilitada para ele ao contrário do TF-IDF que falha.


O BM25 faz duas coisas que o TF-IDF clássico não faz: controle na frequência de termos e ajuste em relação ao tamanho do documento.

Por exemplo, se no documento a palavra coronavirus aparece 100 vezes, no TF-IDF o score aumenta mesmo que seja um documento irrelevante pra pesquisa. O BM25 ele impõe saturação, se tem frequência demais o aumento é imperceptível.

Sobre o tamanho do documento ajustado, o BM25 compara o tamanho de cada texto com a média da base, evitando que os maiores artigos sejam beneficiados só pq são mais verborosos